# Generating Bach Chorales with RNN

In [40]:
import torch
print(torch.__version__)

2.6.0


In [41]:
if torch.cuda.is_available():
    device = torch.device("cuda")
elif torch.backends.mps.is_available():
    device = torch.device("mps")
else:
    device = torch.device("cpu")
device

device(type='mps')

In [42]:
from pathlib import Path
import numpy as np
import pandas as pd
import matplotlib.pyplot as plt

plt.rc('font', size=14)
plt.rc('axes', labelsize=14, titlesize=14)
plt.rc('legend', fontsize=14)
plt.rc('xtick', labelsize=10)
plt.rc('ytick', labelsize=10)

In [43]:
bach_chorales_dir = Path("data/jsb_chorales")

In [44]:
pd.read_csv(Path(bach_chorales_dir / "train" / "chorale_000.csv"))

,note0,note1,note2,note3
0,74,70,65,58
1,74,70,65,58
2,74,70,65,58
3,74,70,65,58
4,75,70,58,55
...,...,...,...,...
187,70,65,62,46
188,70,65,62,46
189,70,65,62,46
190,70,65,62,46


In [45]:
def load_chorales(batch_chorales_dir):
    chorales = {"train": [], "valid": [], "test": []}
    for subseet, _ in chorales.items():
        for chorale_path in (batch_chorales_dir / subseet).glob("*.csv"):
            df = pd.read_csv(chorale_path)
            chorale = torch.tensor(df.values, dtype=torch.long)
            chorales[subseet].append(chorale)
    return chorales

chorales = load_chorales(bach_chorales_dir)

In [46]:
chorales["train"][0].shape, chorales["valid"][0].shape, chorales["test"][0].shape

(torch.Size([180, 4]), torch.Size([244, 4]), torch.Size([180, 4]))

In [47]:
chorales["train"][0][:10]

tensor([[66, 61, 57, 54],
        [66, 61, 57, 54],
        [68, 61, 59, 54],
        [68, 61, 59, 54],
        [69, 66, 61, 54],
        [69, 66, 61, 56],
        [69, 66, 61, 57],
        [69, 66, 61, 59],
        [68, 65, 61, 61],
        [68, 65, 61, 61]])

Listen to the Chorale - This code is copied from [Link!](https://colab.research.google.com/github/ageron/handson-mlp/blob/main/13_processing_sequences_using_rnns_and_cnns.ipynb#scrollTo=vte8gul-dlQr)

In [48]:
from IPython.display import Audio

def notes_to_frequencies(notes):
    # Frequency doubles when you go up one octave; there are 12 semi-tones
    # per octave; Note A on octave 4 is 440 Hz, and it is note number 69.
    return 2 ** ((notes - 69) / 12) * 440

def frequencies_to_samples(frequencies, tempo, sample_rate):
    note_duration = 60 / tempo # the tempo is measured in beats per minutes
    # To reduce click sound at every beat, we round the frequencies to try to
    # get the amplitude close to zero at the end of each note.
    frequencies = (note_duration * frequencies).round() / note_duration
    n_samples = int(note_duration * sample_rate)
    time = torch.linspace(0, note_duration, n_samples)
    sine_waves = torch.sin(2 * torch.pi * frequencies.reshape(-1, 1) * time)
    # Removing all notes with frequencies ≤ 9 Hz (includes note 0 = silence)
    sine_waves *= (frequencies > 9.).reshape(-1, 1)
    return sine_waves.reshape(-1)

def chords_to_samples(chords, tempo, sample_rate):
    freqs = notes_to_frequencies(chords)
    freqs = torch.cat([freqs, freqs[-1:]], dim=0) # make last note a bit longer
    merged = torch.stack([frequencies_to_samples(melody, tempo, sample_rate)
                          for melody in freqs.T]).mean(dim=0)
    n_fade_out_samples = sample_rate * 60 // tempo # fade out last note
    fade_out = torch.linspace(1., 0., n_fade_out_samples)**2
    merged[-n_fade_out_samples:] *= fade_out
    return merged

def play_chords(chords, tempo=160, amplitude=0.1, sample_rate=44100):
    samples = amplitude * chords_to_samples(chords, tempo, sample_rate)
    return display(Audio(samples, rate=sample_rate))

In [49]:
for index in range(3):
    play_chords(chorales["train"][index])

Preprocess Data - This code is copied from [Link!](https://colab.research.google.com/github/ageron/handson-mlp/blob/main/13_processing_sequences_using_rnns_and_cnns.ipynb#scrollTo=vte8gul-dlQr)

In [50]:
import torch.nn.functional as F

def preprocess_note_indices(note_indices, length=None):
    notes_one_hot = F.one_hot(note_indices, num_classes=48).to(torch.float32)
    if length is None:
        length = len(note_indices)

    idx = torch.arange(len(note_indices), dtype=torch.float32,
                       device=note_indices.device).view(-1, 1) - 1
    return torch.cat([
        notes_one_hot,
        idx % 4,
        idx % 16 // 4,
        idx / (length - 1)
    ], dim=-1)

class BachDataset(torch.utils.data.Dataset):
    def __init__(self, chorales, window_length):
        self.chorales = chorales
        self.windows = []
        sos = torch.tensor([1])
        for chorale in chorales:
            notes = chorale.reshape(-1)
            note_indices = torch.cat([sos, F.relu(notes - 34)])
            X = preprocess_note_indices(note_indices)
            for index in range(len(notes) - window_length):
                self.windows.append((
                    X[index : index + window_length],
                    note_indices[index + 1 : index + window_length + 1]
                ))

    def __len__(self):
        return len(self.windows)

    def __getitem__(self, index):
        return self.windows[index]

window_length = 128
train_set = BachDataset(chorales["train"], window_length)
valid_set = BachDataset(chorales["valid"], window_length)
test_set = BachDataset(chorales["test"], window_length)

In [52]:
X, y = train_set[0]
X.shape, y.shape

(torch.Size([128, 51]), torch.Size([128]))

In [53]:
X.round(decimals=2)

tensor([[0.0000, 1.0000, 0.0000,  ..., 3.0000, 3.0000, -0.0000],
        [0.0000, 0.0000, 0.0000,  ..., 0.0000, 0.0000, 0.0000],
        [0.0000, 0.0000, 0.0000,  ..., 1.0000, 0.0000, 0.0000],
        ...,
        [0.0000, 0.0000, 0.0000,  ..., 0.0000, 3.0000, 0.1700],
        [0.0000, 0.0000, 0.0000,  ..., 1.0000, 3.0000, 0.1700],
        [0.0000, 0.0000, 0.0000,  ..., 2.0000, 3.0000, 0.1800]])

In [54]:
X[:, :48].argmax(dim=1)

tensor([ 1, 32, 27, 23, 20, 32, 27, 23, 20, 34, 27, 25, 20, 34, 27, 25, 20, 35,
        32, 27, 20, 35, 32, 27, 22, 35, 32, 27, 23, 35, 32, 27, 25, 34, 31, 27,
        27, 34, 31, 27, 27, 34, 31, 25, 15, 34, 31, 25, 15, 32, 32, 23, 16, 32,
        32, 23, 16, 32, 32, 23, 16, 32, 32, 23, 16, 32, 32, 25, 16, 32, 32, 25,
        16, 34, 32, 25, 16, 34, 32, 25, 16, 35, 32, 27, 15, 35, 32, 27, 15, 35,
        32, 27, 13, 35, 32, 27, 13, 34, 31, 27, 15, 34, 31, 27, 15, 34, 31, 25,
        15, 34, 31, 25, 15, 32, 27, 23,  8, 32, 27, 23,  8, 32, 27, 23,  8, 32,
        27, 23])

In [55]:
y

tensor([32, 27, 23, 20, 32, 27, 23, 20, 34, 27, 25, 20, 34, 27, 25, 20, 35, 32,
        27, 20, 35, 32, 27, 22, 35, 32, 27, 23, 35, 32, 27, 25, 34, 31, 27, 27,
        34, 31, 27, 27, 34, 31, 25, 15, 34, 31, 25, 15, 32, 32, 23, 16, 32, 32,
        23, 16, 32, 32, 23, 16, 32, 32, 23, 16, 32, 32, 25, 16, 32, 32, 25, 16,
        34, 32, 25, 16, 34, 32, 25, 16, 35, 32, 27, 15, 35, 32, 27, 15, 35, 32,
        27, 13, 35, 32, 27, 13, 34, 31, 27, 15, 34, 31, 27, 15, 34, 31, 25, 15,
        34, 31, 25, 15, 32, 27, 23,  8, 32, 27, 23,  8, 32, 27, 23,  8, 32, 27,
        23,  8])

In [56]:
from torch.utils.data import DataLoader

torch.manual_seed(42)
batch_size = 32
train_loader = DataLoader(train_set, batch_size=batch_size, shuffle=True)
valid_loader = DataLoader(valid_set, batch_size=batch_size)
test_loader = DataLoader(test_set, batch_size=batch_size)

In [57]:
from torch import nn

class CausalConv1d(nn.Module):
    def __init__(self, in_channels, out_channels, kernel_size, dilation=1, **kwargs):
        super().__init__()
        self.pad = (kernel_size - 1) * dilation
        self.conv = nn.Conv1d(in_channels, out_channels, kernel_size, padding=self.pad, dilation=dilation, **kwargs)

    def forward(self, x):
        out = self.conv(x)
        return out[:, :, :-self.pad] if self.pad > 0 else out

In [58]:
from torch import nn
class BachModel(nn.Module):
    def __init__(self, n_inputs=51, conv_dim=32, lstm_dim=64, n_notes=48):
        super().__init__()
        conv_layers = []
        for idx in range(4):
            conv_layers += [CausalConv1d(n_inputs, conv_dim, kernel_size=2, dilation=2**idx),
                           nn.ReLU(),
                           nn.BatchNorm1d(conv_dim)]
            n_inputs = conv_dim
        self.conv_stack = nn.Sequential(*conv_layers)
        self.lstm = nn.LSTM(input_size=conv_dim, hidden_size=lstm_dim, batch_first=True)
        self.output = nn.Linear(lstm_dim, n_notes)
    def forward(self, X):
        Z = X.transpose(1, 2)
        Z = self.conv_stack(Z)
        Z = Z.transpose(1, 2)
        Z, _ = self.lstm(Z)
        Z = self.output(Z)
        return Z.transpose(1, 2)
    
torch.manual_seed(42)
bach_model = BachModel().to(device)

In [59]:
import torchmetrics

def evaluate_tm(model, data_loader, metric):
    model.eval()
    metric.reset()
    with torch.no_grad():
        for X_batch, y_batch in data_loader:
            X_batch, y_batch = X_batch.to(device), y_batch.to(device)
            y_pred = model(X_batch)
            metric.update(y_pred, y_batch)
    return metric.compute()

def train(model, optimizer, loss_fn, metric, train_loader, valid_loader,
          n_epochs, patience=10, factor=0.1):
    scheduler = torch.optim.lr_scheduler.ReduceLROnPlateau(
        optimizer, mode="min", patience=patience, factor=factor)
    history = {"train_losses": [], "train_metrics": [], "valid_metrics": []}
    for epoch in range(n_epochs):
        total_loss = 0.0
        metric.reset()
        model.train()
        for X_batch, y_batch in train_loader:
            X_batch, y_batch = X_batch.to(device), y_batch.to(device)
            y_pred = model(X_batch)
            loss = loss_fn(y_pred, y_batch)
            total_loss += loss.item()
            loss.backward()
            optimizer.step()
            optimizer.zero_grad()
            metric.update(y_pred, y_batch)
        history["train_losses"].append(total_loss / len(train_loader))
        history["train_metrics"].append(metric.compute().item())
        val_metric = evaluate_tm(model, valid_loader, metric).item()
        history["valid_metrics"].append(val_metric)
        scheduler.step(val_metric)
        print(f"Epoch {epoch + 1}/{n_epochs}, "
              f"train loss: {history['train_losses'][-1]:.4f}, "
              f"train metric: {history['train_metrics'][-1]:.4f}, "
              f"valid metric: {history['valid_metrics'][-1]:.4f}")
    return history

In [60]:
torch.manual_seed(42)
optimizer = torch.optim.NAdam(bach_model.parameters(), lr=1e-4)
criterion = nn.CrossEntropyLoss()
accuracy = torchmetrics.Accuracy(task='multiclass', num_classes=48).to(device)
history = train(bach_model, optimizer, criterion, accuracy, train_loader, valid_loader, n_epochs=5)

KeyboardInterrupt: 

In [ ]:
evaluate_tm(model, valid_loader, metric).item() * 1e6

NameError: name 'model' is not defined

In [73]:
def generate_chorale(model, seed_chords, num_chords):
    target_length = num_chords * 4 + 1
    notes = seed_chords.to(device).reshape(-1)
    sos = torch.tensor([1], dtype=torch.long, device=device)
    note_indices = torch.cat([sos, F.relu(notes - 34)])
    while len(note_indices) < target_length:
        X = preprocess_note_indices(note_indices, target_length)
        with torch.no_grad():
            new_note_logits = model(X.unsqueeze(0))

        new_note_index = new_note_logits[0, :, -1].argmax(keepdim=True)
        note_indices = torch.cat([note_indices, new_note_index])
        print(f"\r{len(note_indices) / target_length:.1%}", end="")

    notes = note_indices.where(note_indices < 2, note_indices + 34)
    return notes[1:].reshape(-1, 4)

In [74]:
seed_chords = chorales["valid"][1][:8]

In [75]:
torch.manual_seed(42)
chorale = generate_chorale(bach_model, seed_chords, 64).cpu()

100.0%

In [76]:
play_chords(chorale)

In [79]:
def generate_chorale_v2(model, seed_chords, num_chords, temperature=1):
    target_length = num_chords * 4 + 1
    notes = seed_chords.to(device).reshape(-1)
    sos = torch.tensor([1], dtype=torch.long, device=device)
    note_indices = torch.cat([sos, F.relu(notes - 34)])
    while len(note_indices) < target_length:
        X = preprocess_note_indices(note_indices, target_length)
        with torch.no_grad():
            new_note_logits = model(X.unsqueeze(0))

        new_note_probas = F.softmax(new_note_logits[0, :, -1] / temperature, dim=0)
        new_note_index = torch.multinomial(new_note_probas, num_samples=1)
        note_indices = torch.cat([note_indices, new_note_index])
        print(f"\r{len(note_indices) / target_length:.1%}", end="")

    notes = note_indices.where(note_indices < 2, note_indices + 34)
    return notes[1:].reshape(-1, 4)

In [80]:
seed_chords = chorales["valid"][1][:8]
generated_chorales = {}
for temperature in (0.6, 1.0, 1.1):
    torch.manual_seed(42)
    print("Temperature:", temperature)
    chorale = generate_chorale_v2(bach_model, seed_chords, 52, temperature).cpu()
    generated_chorales[temperature] = chorale
    play_chords(chorale)

Temperature: 0.6
100.0%

Temperature: 1.0
100.0%

Temperature: 1.1
100.0%

In [ ]:
import soundfile as sf

def save_chorale(filepath, chords, tempo=160, amplitude=0.1, sample_rate=44100):
    samples = amplitude * chords_to_samples(chords, tempo, sample_rate)
    sf.write(filepath, samples, sample_rate)